### Run this cell first no matter what

In [10]:
from models.records import WeightRecord, WorkoutRecord, ConsumptionRecord, zero_consumption_record, closest_string
from models.fridge import Fridge, FridgeItem
from datetime import date
from models.food import get_details, FoodItem
from reporting.stats import day_stats
from datetime import date
from models.food import parse_foods
from scripts.add_food import add_food
from scripts.update_food import update_comparison_units


foods = parse_foods()
filtered_foods = [food for food in foods if food.name is not None and food.nutrients.per is not None and len(food.comparison_prices) >= 1]

### Log your weight

In [15]:
weight_today = WeightRecord(
    date=date(2026, 10, 11),
    weight=204.4,
    unit='lb'
    )

weight_today.to_csv('src/data/weight.csv')

### Log your workout

In [ ]:
workout = WorkoutRecord(
    date=date.today(),
    type='Overhead Press',
    weight=40.0,
    unit='lb',
    reps=8
)

workout.to_csv('src/data/workouts.csv')

### Log singular item consumed

In [13]:
consumed_item = ConsumptionRecord.construct_consumption('Black Seedless Grapes', 220 - 112, filtered_foods, 0.8)
consumed_item.date = date(2026, 10, 10)
print(consumed_item)

Black Seedless Grapes | 2026-10-10
Amount: 108.00
Price: $1.07
Calories: 75.60
Macronutrients:
  Fat: 0.22 g
    Saturates: 0.11 g
    Trans: 0.00 g
    Polyunsaturates: 0.11 g
  Carbohydrate: 19.44 g
    Sugars: 17.28 g
    Fiber: 1.08 g
    Other carbohydrate: 1.51 g
  Protein: 1.08 g
  Potassium: 216.00 mg
  Cholesterol: 0.00 mg
  Sodium: 2.16 mg
Micronutrients (% daily value):
  Vitamin c: 21.60 %
  Vitamin k: 21.60 %
  Thiamine: 6.48 %
  Riboflavin: 4.32 %
  Vitamin b6: 4.32 %
  Calcium: 0.00 %
  Iron: 2.16 %
  Phosphorus: 2.16 %
  Magnesium: 2.16 %


#### It is a very good idea to print and review the ConsumptionRecord as name search in construct_consumption might not return a match.

In [14]:
consumed_item.to_csv('src/data/food_intake.csv')

### Update database however you like

In [9]:
result = update_comparison_units(
    name="Eggs, Medium",
    new_unit="/ 50g",
    expected_matches=61,
    dry_run=False,
)

print(result)

{'name': 'Eggs, Medium', 'matched': 61, 'changed': 61, 'dry_run': False, 'saved': True, 'examples': [{'product_number': '21685186001_EA', 'before': {'comparison_prices': [{'value': 0.32, 'unit': '50g'}]}, 'after': {'comparison_prices': [{'value': 0.32, 'unit': '/ 50g'}]}}, {'product_number': '21685186001_EA', 'before': {'comparison_prices': [{'value': 0.32, 'unit': '50g'}]}, 'after': {'comparison_prices': [{'value': 0.32, 'unit': '/ 50g'}]}}, {'product_number': '21685186001_EA', 'before': {'comparison_prices': [{'value': 0.32, 'unit': '50g'}]}, 'after': {'comparison_prices': [{'value': 0.32, 'unit': '/ 50g'}]}}]}


#### You can also create 'Meals' by adding ConsumptionRecords together.

In [ ]:
record1 = ConsumptionRecord.construct_consumption('Fusili', 900, filtered_foods, 0.4)
record2 = ConsumptionRecord.construct_consumption('Extra Lean Ground Beef', 1000, filtered_foods, 0.8)
record3 = ConsumptionRecord.construct_consumption('Red Onion', 160, filtered_foods, 0.8)
record4 = ConsumptionRecord.construct_consumption('Jalapeno Peppers', 84, filtered_foods, 0.8)
record5 = ConsumptionRecord.construct_consumption('Bananas, Bunch', 84, filtered_foods, 0.8)


total = zero_consumption_record()

total = record1 + record2 + record3 + record4
total.item = 'Kiymali Makarna'

fridge = Fridge()
fridge_item = FridgeItem(meal=total)
fridge.items.append(fridge_item)

#Feel free to save the meal to your fridge so that you can easily load it back up and compute how much of it you ate.
fridge.save_state('src/data/fridge.json')

#### Update your fridge when you eat the meal and have leftovers

In [19]:
loaded_fridge = Fridge.load_state('src/data/fridge.json')
eaten_mix = loaded_fridge.items[0].eat(400 + 446)
yogurt = ConsumptionRecord.construct_consumption('Original Balkan Style Plain Yogurt 6%', 190, filtered_foods, 0.8)
banana = ConsumptionRecord.construct_consumption('Bananas', 288, filtered_foods, 0.8)
grapes = ConsumptionRecord.construct_consumption('Black Seedless Grapes', 265, filtered_foods, 0.8)
pickles = ConsumptionRecord.construct_consumption('Bread & Butter Sweet Pickles', 80, filtered_foods, 0.8)




for consumption in [eaten_mix, yogurt, banana, grapes]:
    consumption.date = date(2026,10,6)
    consumption.to_csv('src/data/food_intake.csv')

loaded_fridge.save_state('src/data/fridge.json')



### Grab the data of a FoodItem that is missing from your dataset.

In [17]:
from data.auto_scrape import url_to_json_with_retry
import undetected_chromedriver as uc

driver = uc.Chrome(
                headless=False,
                use_subprocess=False,
                version_main=154
            )
url = 'https://www.nofrills.ca/en/bread-butter-sweet-pickles/p/20433560001_EA?source=nspt&search-bar=Bread+and+butter+pickles&storeId=7937&cartId=b01f567b-21e9-448a-af99-3eba25222464'
url_to_json_with_retry(url, driver, page_number=1, count=1)

Merged 'Bread & Butter Sweet Pickles' into data/products.json under Home > Food > Pantry > Canned & Pickled > Pickles


True

### Add the data of any product you like to the database

In [ ]:
new_food = {
    "name": "Sourdough Batard",
    "price": 4.50,
    "price_display": "$4.50",
    "comparison_prices": [
        {
            "value": 0.78,  # Replace with the actual price per unit.
            "unit": "100g",
        },
    ],
    "average_weight": None,  # Total loaf weight, e.g. "450 g".
    "product_number": None,
    "description": None,
    "ingredients": {
        "raw": None,   # Full ingredient label.
        "items": [],   # Individual ingredient strings.
    },
    "nutrients": {
        "per": "75 g",
        "calories": "170 kcal",
        "macronutrients": {
            "fat": {
                "total": "1 g",
                "saturates": "0.2 g",
                "+ trans": "0 g",
                "monounsaturates": "0 g",
                "polyunsaturates": "0 g",
                "omega-3 fatty acids": "0 g",
            },
            "carbohydrate": {
                "total": "35 g",
                "sugars": "1 g",
                "fiber": "2 g",
                "other carbohydrate": "0 g",
            },
            "protein": "6 g",
            "potassium": "75 mg",
            "cholesterol": "0 mg",
            "sodium": "300 mg",
        },
        "micronutrients_percent": {
            "vitamin a": "0%",
            "vitamin c": "0%",
            "vitamin d": "0%",
            "vitamin e": "0%",
            "vitamin k": "0%",
            "thiamine": "0%",
            "riboflavin": "0%",
            "niacin": "0%",
            "vitamin b6": "0%",
            "folate": "0%",
            "vitamin b12": "0%",
            "pantothenate": "0%",
            "biotin": "0%",
            "calcium": "1%",
            "iron": "13%",
            "phosphorus": "0%",
            "magnesium": "0%",
            "zinc": "0%",
            "selenium": "0%",
            "chromium": "0%",
        },
    },
    "breadcrumb": [],
}

print("Added:", add_food(new_food))

#### Read the data of the FoodItem of your choice.

In [ ]:
filtered_foods = [food for food in foods if food.name is not None and food.nutrients.per is not None and len(food.comparison_prices) == 1]
query_food = get_details('1% Kefir, Plain', filtered_foods)
print(query_food)


FoodItem(name='1% Kefir, Plain', price=None, price_display=None, comparison_prices=[ComparisonPrice(value=0.53, unit='/ 100ml')], average_weight=None, product_number='21216416_EA', description='Taste. Made simple. Crafted the Liberté way. Liberté Plain Kefir. This is essentially fermented milk with a pleasing combination of milky and tart and the texture of drinkable yogurt. There are many ways to try Liberté Kefir including cereal, smoothies, salad dressings or alone. This feature over two billion probiotics. Liberté Kefir contains no gelatin and no artificial colours or flavours. This is perfect for breakfast or afternoon with your favourite kids snacks. Contains one 1 litre bottle. 3/4 cupSMOOTH TASTY KEFIR: Liberté Kefir is made of 1% milk fat and features a drinkable yogurt texture; Crafted the Liberté wayPLAIN FLAVOUR: At Liberté, the attention we pay to creating yogurt in its simplest form - plain - is our most preciously guarded secret; Naturally, the choice of ingredients is c

### Observe your daily stats

In [16]:
result = day_stats(date(2026, 10, 10))
print(result)

Total | 2026-10-10
Amount: 821.00
Price: $5.44
Calories: 737.38
Macronutrients:
  Fat: 23.28 g
    Saturates: 7.35 g
    Trans: 0.00 g
    Monounsaturates: 0.00 g
    Polyunsaturates: 0.42 g
    Omega 3 fatty acids: 0.00 g
  Carbohydrate: 96.54 g
    Sugars: 31.61 g
    Fiber: 8.22 g
    Other carbohydrate: 4.28 g
  Protein: 39.95 g
  Potassium: 1,431.34 mg
  Cholesterol: 715.38 mg
  Sodium: 761.69 mg
Micronutrients (% daily value):
  Vitamin a: 0.00 %
  Vitamin c: 89.08 %
  Vitamin d: 0.00 %
  Vitamin e: 0.00 %
  Vitamin k: 52.80 %
  Thiamine: 12.72 %
  Riboflavin: 10.56 %
  Niacin: 0.00 %
  Vitamin b6: 21.88 %
  Folate: 0.00 %
  Vitamin b12: 0.00 %
  Pantothenate: 6.24 %
  Biotin: 8.47 %
  Calcium: 10.20 %
  Iron: 47.49 %
  Phosphorus: 10.09 %
  Magnesium: 16.33 %
  Zinc: 6.24 %
  Selenium: 0.00 %
  Chromium: 0.00 %


##### testing stuff

In [5]:
for food in filtered_foods:
    if 'ml' in food.comparison_prices[0].unit:
        # if (not food.comparison_prices[0].value) and (not food.comparison_prices[0].unit):
        print(food)

FoodItem(name='Coffee Creamer, French Vanilla', price=5.99, price_display='$5.99 est.', comparison_prices=[ComparisonPrice(value=0.63, unit='/ 100ml')], average_weight=None, product_number='20895480002_EA', description='Smooth, creamy vanilla flavour inspired by the rich, French style of ice cream. A little French vanilla in your cup helps you ease into a smoother, dreamier state of mind. Create a cup of coffee that sweeps you off your feet.Welcome to the #CreamerNation – Expect to be DelightedOnly 35 calories per 15ml servingInternational Delight coffee creamer products are gluten-free and caffeine freeCholesterol and lactose freeCrafted for coffee', ingredients=Ingredients(raw='Water, Sugar, Palm Oil, Sodium Caseinate* (milk), Dipotassium Phosphate, Sodium Citrate, Carrageenan, Mono And Diglycerides, Sodium Stearoyl Lactylate, Salt, Natural And Artificial Flavours. *sodium Caseinate Is Not A Source Of Lactose.', items=['Water', 'Sugar', 'Palm Oil', 'Sodium Caseinate* (milk)', 'Dipota

In [ ]:
print(filtered_foods[0])